In [1]:
import os
import numpy as np
import pdfplumber
import faiss

from google import genai
from dotenv import load_dotenv
from langchain_text_splitters import RecursiveCharacterTextSplitter

load_dotenv()

api_key=os.getenv("GEMINI_API_KEY")

if not api_key:
    raise ValueError("GEMINI_API_KEY is missing from .env file")

client = genai.Client(api_key=api_key)

EMBEDDING_MODEL = "gemini-embedding-001"
GENERATION_MODEL = "gemini-2.5-flash-lite"

print("Gemini client initialized!")



d:\JEEVA\GENAI\venv\Lib\site-packages\tqdm\auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


Gemini client initialized!


In [2]:

pdf_path = r"D:\JEEVA\GENAI\Ai_with_Rag\7th_Science.pdf"
all_text = []

with pdfplumber.open(pdf_path) as pdf:
    print("Total Pages: ", len(pdf.pages))
    
    for page_num, page in enumerate(pdf.pages,start=1):
        page_text = page.extract_text() or "" 
        
        if page_text.strip():
            all_text.append(
                f"\n --- Page {page_num} --- \n {page_text}"
            )
full_text="\n".join(all_text)

if not full_text.strip():
    raise ValueError(
        "No text extracted. The PDF may be scanned or image-based."
    )
    
print("Total character: ",len(full_text))
print(full_text[:500])
print("PDF text extracted successfully!")




Total Pages:  97
Total character:  166136

 --- Page 1 --- 
 www.tntextbooks.in
GOVERNMENT OF TAMIL NADU
STANDARD SEVEN
TERM - II
VOLUME - 3
SCIENCE
SOCIAL SCIENCE
A publication under Free Textbook Programme of Government of Tamil Nadu
Department of School Education
Untouchability is Inhuman and a Crime
VII Std Science Term-1 EM Introduction Pages.indd 1 20-07-2019 1.46.04 PM

 --- Page 2 --- 
 www.tntextbooks.in
Government of Tamil Nadu
First Edition - 2019
(Published under New Syllabus in
Trimester Pattern)
NOT FOR SALE
Content Creati
PDF text extracted successfully!


In [7]:
text_splitter = RecursiveCharacterTextSplitter(
    chunk_size = 800,
    chunk_overlap=100,
    separators=["\n\n", "\n", " ",""]
)

chunks = text_splitter.split_text(full_text)

if not chunks:
    raise ValueError("No chunks were created")

print("Total Chunks:", len(chunks))
print("\n First Chunk: \n")

print(chunks[0])



Total Chunks: 282

 First Chunk: 

--- Page 1 --- 
 www.tntextbooks.in
GOVERNMENT OF TAMIL NADU
STANDARD SEVEN
TERM - II
VOLUME - 3
SCIENCE
SOCIAL SCIENCE
A publication under Free Textbook Programme of Government of Tamil Nadu
Department of School Education
Untouchability is Inhuman and a Crime
VII Std Science Term-1 EM Introduction Pages.indd 1 20-07-2019 1.46.04 PM

 --- Page 2 --- 
 www.tntextbooks.in
Government of Tamil Nadu
First Edition - 2019
(Published under New Syllabus in
Trimester Pattern)
NOT FOR SALE
Content Creation
The wise
possess all
State Council of Educational Research
and Training
© SCERT 2019
Printing & Publishing
Tamil NaduTextbook and Educational
Services Corporation
www.textbooksonline.tn.nic.in
II
VII Std Science Term-1 EM Introduction Pages.indd 2 20-07-2019 1.46.05 PM


In [8]:
def convert_embed(text):
    result = client.models.embed_content(
        model = EMBEDDING_MODEL,
        contents=text
    )
    
    return result.embeddings[0].values

chunk_embeddings = []

for i, chunk in enumerate(chunks):
    
    embedding = convert_embed(chunk)
    
    chunk_embeddings.append(embedding)
    
    if (i + 1) % 10 == 0 or (i + 1) == len(chunks):
        print(f"Embedded {i + 1}/{len(chunks)} chunks")

print(chunk_embeddings,'chunk_embeddings-----1')
chunk_embeddings = np.array(
    chunk_embeddings,
    dtype=np.float32
)

print(chunk_embeddings,'chunk_embeddings-----2')

print("Embedding array shape:", chunk_embeddings.shape)

  

Embedded 10/282 chunks
Embedded 20/282 chunks
Embedded 30/282 chunks
Embedded 40/282 chunks
Embedded 50/282 chunks
Embedded 60/282 chunks
Embedded 70/282 chunks
Embedded 80/282 chunks
Embedded 90/282 chunks
Embedded 100/282 chunks
Embedded 110/282 chunks
Embedded 120/282 chunks
Embedded 130/282 chunks
Embedded 140/282 chunks
Embedded 150/282 chunks
Embedded 160/282 chunks
Embedded 170/282 chunks
Embedded 180/282 chunks
Embedded 190/282 chunks
Embedded 200/282 chunks
Embedded 210/282 chunks
Embedded 220/282 chunks
Embedded 230/282 chunks
Embedded 240/282 chunks
Embedded 250/282 chunks
Embedded 260/282 chunks
Embedded 270/282 chunks
Embedded 280/282 chunks
Embedded 282/282 chunks
[[0.014793602, -0.002609063, 0.0096572675, -0.030332869, -0.009079205, 0.002551769, 0.035702422, -0.0035095888, 0.0017823118, 0.010737117, 0.00785765, -0.0022682224, -0.009546167, 0.01582955, 0.13400184, 0.00811526, -0.016737375, -0.009820936, 0.0027379787, 0.007877957, 0.010397989, -0.0002118979, 0.007226672, -

In [9]:
dimension = chunk_embeddings.shape[1]

print(chunk_embeddings.shape[0])
print(dimension,'dimension---')

index = faiss.IndexFlatL2(dimension)

index.add(chunk_embeddings)

documents = chunks.copy()

print("FAISS index created!")
print("Vectors stored:", index.ntotal)
print("Documents stored:", len(documents))



282
3072 dimension---
FAISS index created!
Vectors stored: 282
Documents stored: 282


In [28]:
def retrieve_documents(question,top_k=3):
    
    query_embedding = convert_embed(question)
    print(query_embedding[:10],"query_embedding")
    print("query_embedding_datatype",type(query_embedding))
    
    quer_vector = np.array([query_embedding],dtype=np.float32)
    print(quer_vector[:10],'quer_vector--------')
    print("quer_vector_dtype",quer_vector.dtype)
    
    k=min(top_k,index.ntotal)
    
    if k == 0:
        return []
    
    distances,indices = index.search(quer_vector,k)
    
    print(distances,'distances')
    print(indices,'indices')
    retrieved_chunks = []
    
    for i,idx in enumerate(indices[0]):
        if idx != -1 and distances[0][i] >= 0.60:
            retrieved_chunks.append({
                "text":documents[idx],
                "distance": float(distances[0][i])
            })
    
    print(len(retrieved_chunks))
    return retrieved_chunks
    

In [ ]:
question = "Which organelle uses energy from sunlight to make starch"

results = retrieve_documents(question, top_k=3)

print(results,"results")

for rank, item in enumerate(results, start=1):
    print(f"\nResult {rank}")
    print("Distance:", round(item["distance"], 4))
    print("Text:", item["text"])

[0.021472163, 0.0014431898, -0.00795606, -0.077328555, 0.0002638398, 0.01706845, 0.005687636, 0.0036544467, 0.004944223, -0.00016287205] query_embedding
query_embedding_datatype <class 'list'>
[[ 0.02147216  0.00144319 -0.00795606 ... -0.00512593  0.02044382
  -0.02697548]] quer_vector--------
quer_vector_dtype float32
[[0.6394125 0.6660516 0.7523519]] distances
[[204 205 215]] indices
3
[{'text': '--- Page 69 --- \n www.tntextbooks.in\nChloroplast- “Food Producers”.\nVarious range of these\nDo you notice the green organelles\nplastids impart different\npresent in plant cells and absent in animal cells.\ncolours to various parts of\nChloroplasts are the only cell organelles that\nplant. Chromoplast impart\ncan produce food from the\ncolour to flower and fruits. As fruits ripen,\nsun energy. Only plants with\nchloroplasts change to chromoplasts.\nchloroplast are able to do\nStarch is converted to sugar.\nphotosynthesis because they\ncontain the very important\nGolgi Complex- I need a br

In [ ]:
def ask_pdf_question(question, top_k=3):

    # Step 1: Retrieve relevant chunks
    results = retrieve_documents(question, top_k)

    if not results:
        return "No relevant document chunks were found."

    # Step 2: Combine retrieved chunks into context
    context = "\n\n".join(
        item["text"] for item in results
    )
    
    print(context,'context-------')

    # Step 3: Create the prompt
    prompt = f"""
You are a helpful assistant that answers questions using a PDF.

Use only the information provided in the context.
If the answer is not available in the context, clearly say:
"I could not find this information in the provided PDF."

Context:
{context}

User question:
{question}

Answer:
"""

    # Step 4: Generate the answer
    response = client.models.generate_content(
        model=GENERATION_MODEL,
        contents=prompt
    )

    return response.text

In [33]:
question = "how to drive aeroplane"

answer = ask_pdf_question(question, top_k=3)

print("\nAnswer:")
print(answer)

[-0.00643514, -0.012165131, 0.01514982, -0.060812205, -0.018173315, 0.004110841, -0.0051872046, -0.005577871, -0.010247525, 0.017452532] query_embedding
query_embedding_datatype <class 'list'>
[[-0.00643514 -0.01216513  0.01514982 ...  0.00992057  0.00599992
  -0.01011199]] quer_vector--------
quer_vector_dtype float32
[[0.86284864 0.8996614  0.9051962 ]] distances
[[270 272 269]] indices
3

Answer:
I could not find this information in the provided PDF.


In [36]:
documents[269]

'right side. This tool provides\nNew Ctrl+N\ncountless number of special visual effects if it is\nOpen Ctrl+O\nused in various combination with other tools.\nSave Ctrl + S\nThis tool can be used either by clicking or by\nPrint Ctrl+P\ndragging the effect directly on to the image to\nQuit Esc\napply it.\nUndo Ctrl + Z\nThis tool is appears similar to the Redo Ctrl+Y\nPaint Brush, but it is used to erase\nTux Math\nthe picture.\nTux Math is an open source arcade – style\nThis tool is used to cancel a\nvideo game for learning arithmetic. The main\ncommand given earlier.\ngoal is to make learning effective and fun.\nTittle Screen\nThis tool is used to reverse the\nMath Command Training Academy:\naction of Undo.\nchoose this to go to a list of over fifty\nprepared lessons, starting with simple typing\n89'

In [39]:
a=["1","2","3"]
print("".join(a))

123


#### ruban
jeeva